## CMM POS Feed: Omnichannel Model

### Setup

#### Srv Principal

In [0]:
%run /Shared/KrPrtnrs_service_principal

#### Libraries

In [0]:
%run "./file_utils_nb"

In [0]:
from pyspark import storagelevel
from pyspark import SparkContext
from pyspark.sql import DataFrame as SparkDataFrame
from pyspark.sql import SparkSession, Row
from pyspark.sql.window import Window
import pyspark.sql.functions as f
from pyspark.sql.functions import col, when, count, countDistinct
from pyspark.sql.types import *
import pandas as pd
import numpy as np
from datetime import datetime, timedelta
import seg
from seg.utils import DateType
from effodata import ACDS, golden_rules, effodata, Joiner, Sifter, Equality
from kpi_metrics import KPI, AliasMetric, CustomMetric, AliasGroupby, Rollup, Cube, available_metrics, get_metrics
from kayday import KrogerDate
import seg
import random
import string

# options
pd.set_option('display.max_columns', 100)
spark.conf.set("spark.databricks.io.cache.enabled", "true")
spark.conf.set("spark.sql.shuffle.partitions", "auto")
spark.conf.set("spark.default.parallelism", "264")

#### Parameters

In [0]:
# Widgets

dbutils.widgets.text(
  name = "start_date", 
  defaultValue = "", 
  label = "Cal Start Date (YYYYMMDD)")

dbutils.widgets.text(
  name = "end_date", 
  defaultValue = "", 
  label = "Cal End Date (YYYYMMDD)")
  

In [0]:
# define working directory
wd = 'abfss://tmkrprtnrs-users@sa8451krprtnrdev.dfs.core.windows.net/l920466/ap-pos-feed'

# Set dates and variables:
db = 'l920466_cmm'
#spark.sql(f'create schema if not exists {db}')
run_id = ''.join(random.choice(string.ascii_letters) for x in range(5))
start_date = dbutils.widgets.get('start_date')
end_date = dbutils.widgets.get('end_date')
fiscal_week = KrogerDate(date=end_date).format_week().replace("F", "")
fiscal_week_prev = (KrogerDate(date=end_date) - timedelta(weeks=1)).format_week().replace("F", "")
fiscal_week_prev_month = (KrogerDate(date=end_date) - timedelta(weeks=4)).format_week().replace("F", "")
start_week = KrogerDate(date=start_date).format_week().replace("F", "")
end_week = fiscal_week
mode = 'overwrite'
print_output = False
write_output = True
use_sample_mart = False
modality_name = 'enterprise_nonship'

# print parameters
print("run_id: " + run_id)
print("start date: " + start_date)
print("end_date: " + end_date)
print("start_week: " + start_week)
print("end_week: " + end_week)
print("fiscal_week: " + fiscal_week)
print("fiscal_week_prev: " + fiscal_week_prev)
print("last week of previous month: " + fiscal_week_prev_month)
print("write mode: " + mode)

run_id: BOedw
start date: 20250720
end_date: 20250816
start_week: 20250701
end_week: 20250704
fiscal_week: 20250704
fiscal_week_prev: 20250703
last week of previous month: 20250604
write mode: overwrite


#### UDFs

In [0]:
# function for creating a named csv file

def create_named_csv(sdf, path, file_name, fiscal_week, mode = 'overwrite'):
  # create a named csv file from dataframe
  sdf_out = sdf\
    .coalesce(1)\
    .write\
    .format('csv')\
    .mode(mode)\
    .option("header", True)\
    .option("quote", "")\
    .save(path+f'/temp_files_{run_id}')

  if mode == 'overwrite':
    # copy temp files to named file
    data_location = path+f'/temp_files_{run_id}'
    files = dbutils.fs.ls(data_location)
    csv_file = [x.path for x in files if x.path.endswith('.csv')][0]
    dbutils.fs.cp(
      csv_file, 
      (path + "/" + file_name + "_" + fiscal_week + "_" + format(datetime.now(), "%Y%m%d_%H%M%S") + '.csv'))
    dbutils.fs.rm(data_location, recurse=True) 
  
def file_exists(path):
  """
  Check to see if file exists in databricks
  """
  try:
    dbutils.fs.ls(path)
    return True
  except Exception as e:
    if 'java.io.FileNotFoundException' in str(e):
      return False
    else:
      raise

In [0]:
# function for logging dates and counts

def log_counts(sdf, path, fiscal_week, mode = 'overwrite'):
# add fiscal_date to dates_completed.csv for logging counts
  dates_completed = spark.read.csv(path + "/dates_completed.csv", header=True)
  cols = ['fiscal_date', 'record_count']
  vals = [(fiscal_week, sdf.count())]
  new = spark.createDataFrame(vals, cols)
  new_dates_completed = new.union(dates_completed).orderBy(f.col('fiscal_date').desc())
  new_dates_completed.write.mode(mode).csv(path + '/dates_completed', header=True)
  
  # write dates_completed to abfss
  data_location = path + '/dates_completed'
  files = dbutils.fs.ls(data_location)
  csv_file = [x.path for x in files if x.path.endswith('.csv')][0]
  dbutils.fs.cp(csv_file, data_location.rstrip('/') + '.csv')
  dbutils.fs.rm(data_location, recurse=True)

### Data

#### ACDS

In [0]:
# transactions data store
acds = ACDS(use_sample_mart=use_sample_mart)
kpi = KPI(use_sample_mart=use_sample_mart)

#### Preferred Store

In [0]:
# get weekly
pref_div = spark.read.parquet(
  "abfss://acds@sa8451posprd.dfs.core.windows.net" + 
  "/preferred_store/fiscal_week=" + fiscal_week)\
  .withColumn('pref_div', f.substring(f.col('pref_store_code_1'), 1, 3))

if print_output:
  pref_div.limit(10).display()

#### Bigfoot Vintages

In [0]:
# added 2024-01-09
# read in bigfoot vintages for instore and ecomm, and combine to get latest purchase
# Select min of first week they ever shopped to get first occurence, and get min of weeks since mod visit to get most recent time elapsed since visit

# If customer is in store in 2020 and ecomm in 2023, vintage wk would be 2020
# if customer has not shopped in store since 2020 but delivered last wk, weeks since mod visit would be 1
bf_instore = spark.read.parquet(abfss.path_digitalinsights + f'/customer_data_assets/bigfoot/prod/modality=instore/end_week={fiscal_week}')

bf_instore_prev = spark.read.parquet(abfss.path_digitalinsights + f'/customer_data_assets/bigfoot/prod/modality=instore/end_week={fiscal_week_prev_month}')\
  .select('ehhn', 'vintage_week', 'weeks_since_mod_visit')

bf_ecomm = spark.read.parquet(abfss.path_digitalinsights + f'/customer_data_assets/bigfoot/prod/modality=ecommerce/end_week={fiscal_week}')

bf_ecomm_prev = spark.read.parquet(abfss.path_digitalinsights + f'/customer_data_assets/bigfoot/prod/modality=ecommerce/end_week={fiscal_week_prev_month}')\
  .select('ehhn', 'vintage_week', 'weeks_since_mod_visit')

# last week vintage vs this weeks vintage 
bf_combined = bf_instore.union(bf_ecomm).groupBy('ehhn').agg(f.min(f.col('vintage_week')).alias('vintage_week'), 
                                                             f.min(f.col('weeks_since_mod_visit')).alias('weeks_since_mod_visit'))

bf_combined_prev = bf_instore_prev.union(bf_ecomm_prev).groupBy('ehhn').agg(f.min(f.col('vintage_week')).alias('vintage_week'), 
                                                             f.min(f.col('weeks_since_mod_visit')).alias('weeks_since_mod_visit'))

bf_combined.limit(10).display()
bf_combined_prev.limit(10).display()

ehhn,vintage_week,weeks_since_mod_visit
301203802,20160502,4
340816076,20180104,389
11771600002,20190702,315
12061000142,20190703,314
1163200126,20180602,53
278862878,20211004,4
135106743,20160202,6
330853681,20170804,414
340317361,20180102,0
52306800273,20230403,118


ehhn,vintage_week,weeks_since_mod_visit
334190572,20171003,289
64597800422,20241003,37
332899292,20171001,405
64065500094,20240903,41
313774698,20161101,290
21266400158,20231203,70
48187500365,20221204,133
6176400400,20181301,340
262035706,20241103,33
231820317,20160101,0


#### Golden Rules

In [0]:
# Define golden rules to model what was previously sent to AP
# updated from default to remove wags div 105, add 504 (Ocado)
# remove ehhn_0, cus_act_no_0, and ehhn_null exclusions
# add additional recap dept exclusions: 'CC', 'XX', 'KB', 'DEFAULT_HIERARCHY'

grs = golden_rules()

grs_new = grs\
  .update_exclusion(
    set_name="store_exclusions",
    exclusion_name="division_excl", 
    sql=grs.store_exclusions.division_excl.sql.replace(", '105'", ""))\
  .update_exclusion(
    set_name="store_exclusions",
    exclusion_name="division_excl",
    sql="geo_div_no not in ('011','014','016','018','021','024','025','026','029','034','035','540','531','534','615','620','660','701','703','705','706') and geo_div_no not like '540%'", 
    table="stores")\
  .update_exclusion(
    set_name="product_exclusions",
    exclusion_name="pid_fyt_rec_dpt_cd_excl",
    sql="pid_fyt_rec_dpt_cd in ('06', '30', '34', '58', '78', 'CC', 'XX', 'KB', 'DEFAULT_HIERARCHY')",
    table="products")\
  .remove(set_name="customer_exclusions", exclusion_name=["ehhn_0", "cus_act_no_0", "ehhn_null"])

print("Golden rules used: \n")
grs_new

Golden rules used: 



golden_rules(which=['third_party_exclusions', 'fuel_exclusions', '...', '...', '...'])

#### Create Lapsed segment

In [0]:
# dates = acds.dates.select('fiscal_week', 'fiscal_month').distinct().withColumnRenamed('fiscal_Week', 'vintage_week')

In [0]:
# fiscal_week = [20240701, 20240702, 20240703, 20240704, 20240801, 20240802, 20240803, 20240804, 20240901, 20240902, 20240903, 20240904, 20241001, 20241002, 20241003, 20241004]

# bf_omni_df = None

# for week in fiscal_week:
#   bf_instore = spark.read.parquet(abfss.path_digitalinsights + f'/customer_data_assets/bigfoot/prod/modality=instore/end_week={week}')
#   bf_ecomm = spark.read.parquet(abfss.path_digitalinsights + f'/customer_data_assets/bigfoot/prod/modality=ecommerce/end_week={week}')

#   bf_combined = bf_instore.union(bf_ecomm).groupBy('ehhn').agg(f.min(f.col('vintage_week')).alias('vintage_week'), 
#                                                              f.min(f.col('weeks_since_mod_visit')).alias('weeks_since_mod_visit'))

#   temp_df = bf_combined\
#     .join(dates, how = 'inner', on = 'vintage_week') \
#     .withColumn('omni_seg', f.when(f.col('vintage_week') == week, 'new')) \
#     .select('ehhn', 'vintage_week', 'fiscal_month','omni_seg') \
#       .filter(f.col('omni_seg') == 'new')
#   if bf_omni_df is None:
#     bf_omni_df = temp_df
#   else:
#     bf_omni_df = bf_omni_df.unionByName(temp_df)

# bf_omni_df.groupBy('fiscal_month').agg(f.countDistinct('ehhn').alias('new_hhs')).display()

In [0]:
# fiscal_week = [20250701, 20250702, 20250703, 20250704, 20250801, 20250802, 20250803, 20250804, 20250901, 20250902, 20250903, 20250904, 20251001, 20251002, 20251003, 20251004]

# bf_omni_df = None

# for week in fiscal_week:
#   bf_instore = spark.read.parquet(abfss.path_digitalinsights + f'/customer_data_assets/bigfoot/prod/modality=instore/end_week={week}')
#   bf_ecomm = spark.read.parquet(abfss.path_digitalinsights + f'/customer_data_assets/bigfoot/prod/modality=ecommerce/end_week={week}')

#   bf_combined = bf_instore.union(bf_ecomm).groupBy('ehhn').agg(f.min(f.col('vintage_week')).alias('vintage_week'), 
#                                                              f.min(f.col('weeks_since_mod_visit')).alias('weeks_since_mod_visit'))

#   temp_df = bf_combined\
#     .join(dates, how = 'inner', on = 'vintage_week') \
#     .withColumn('omni_seg', f.when(f.col('vintage_week') == week, 'new')) \
#     .select('ehhn', 'vintage_week', 'fiscal_month','omni_seg') \
#       .filter(f.col('omni_seg') == 'new')
#   if bf_omni_df is None:
#     bf_omni_df = temp_df
#   else:
#     bf_omni_df = bf_omni_df.unionByName(temp_df)

# bf_omni_df.groupBy('fiscal_month').agg(f.countDistinct('ehhn').alias('new_hhs')).display()

In [0]:
# Base customer group is all ehhns in bigfoot: ecommerce + instore modality
# logic for lapsed customers is based on 'number of weeks since last visit' 
# as defined in the bigfoot dataset

# Determine segmentation based on prior week's vintage
# This is needed because in the next step, a modifier will be add to 'reactivated'
# households based on their prior lapsed behavior from the prior week.
enterprise_seg_prev = bf_combined_prev\
  .withColumn(
    'enterprise_seg_prev', 
    f.when(f.col('weeks_since_mod_visit') < 52, 'active_under_52_wks')\
        .when(f.col('weeks_since_mod_visit') >= 52, 'lapsed_52_plus_wks')\
    .otherwise(None))\
  .select('ehhn', 'enterprise_seg_prev')

# EHHN and category (whether EHHN is active or lapsed)
enterprise_seg_prev.display()

# CURRENT WEEK: Determine current segmentation with 'reactivated' and prev segment modifier for reactivated.
# Reactivated means that their weeks since last visit between 0 to 3 to show they've started visiting anytime the last month
enterprise_seg_curr = bf_combined\
  .join(enterprise_seg_prev, on = 'ehhn', how = 'left')\
  .withColumn('enterprise_seg', 
    f.when(((f.col('vintage_week') >= start_week) & (f.col('vintage_week') <= end_week)), 'new')\
    .when(
      # Was previously lapsed, but visited within the last 3 week -> Reactivated
      (f.col('weeks_since_mod_visit').isin(0,1,2,3)) &
      (f.col('enterprise_seg_prev') == 'lapsed_52_plus_wks'), 'active_reactivated_from_lapsed_52_plus_wks')\
    .when(f.col('weeks_since_mod_visit') < 52, 'active_under_52_wks')\
      .when(f.col('weeks_since_mod_visit')>=52, 'lapsed_52_plus_wks') \
    .otherwise(None))\
  .select('ehhn', 'enterprise_seg', 'weeks_since_mod_visit') \
  .filter(f.col('enterprise_seg').isin('new', 'active_reactivated_from_lapsed_52_plus_wks'))

enterprise_seg_curr.display()

ehhn,enterprise_seg_prev
334190572,lapsed_52_plus_wks
64597800422,active_under_52_wks
332899292,lapsed_52_plus_wks
64065500094,active_under_52_wks
313774698,lapsed_52_plus_wks
21266400158,lapsed_52_plus_wks
48187500365,lapsed_52_plus_wks
6176400400,lapsed_52_plus_wks
262035706,active_under_52_wks
231820317,active_under_52_wks


ehhn,enterprise_seg,weeks_since_mod_visit
10003000053,active_reactivated_from_lapsed_52_plus_wks,3
100056298,active_reactivated_from_lapsed_52_plus_wks,3
10016200113,active_reactivated_from_lapsed_52_plus_wks,0
10020418,active_reactivated_from_lapsed_52_plus_wks,3
10034448,active_reactivated_from_lapsed_52_plus_wks,1
100401930,active_reactivated_from_lapsed_52_plus_wks,0
100546928,active_reactivated_from_lapsed_52_plus_wks,3
100556997,active_reactivated_from_lapsed_52_plus_wks,3
100607234,active_reactivated_from_lapsed_52_plus_wks,1
100661260,active_reactivated_from_lapsed_52_plus_wks,3


In [0]:
#QA
enterprise_seg_curr.groupBy('enterprise_seg').count().display()

enterprise_seg,count
active_reactivated_from_lapsed_52_plus_wks,461580
new,938800


#### April 2026 Edit: Add Existing Last 52 Weeks HHs 
- Section for just my changes for visibility

In [0]:
# Base customer group is all ehhns in bigfoot: ecommerce + instore modality
# logic for lapsed customers is based on 'number of weeks since last visit' 
# as defined in the bigfoot dataset

# Determine segmentation based on prior week's vintage
# This is needed because in the next step, a modifier will be add to 'reactivated'
# households based on their prior lapsed behavior from the prior week.
enterprise_seg_prev = bf_combined_prev\
  .withColumn(
    'enterprise_seg_prev', 
    f.when(f.col('weeks_since_mod_visit') < 52, 'active_under_52_wks')\
        .when(f.col('weeks_since_mod_visit') >= 52, 'lapsed_52_plus_wks')\
    .otherwise(None))\
  .select('ehhn', 'enterprise_seg_prev')

# EHHN and category (whether EHHN is active or lapsed)
enterprise_seg_prev.display()

# CURRENT WEEK: Determine current segmentation with 'reactivated' and prev segment modifier for reactivated.
# Reactivated means that their weeks since last visit between 0 to 3 to show they've started visiting anytime the last month
enterprise_seg_curr = bf_combined\
  .join(enterprise_seg_prev, on = 'ehhn', how = 'left')\
  .withColumn('enterprise_seg', 
    f.when(((f.col('vintage_week') >= start_week) & (f.col('vintage_week') <= end_week)), 'new')\
    .when(
      # Was previously lapsed, but visited within the last 3 week -> Reactivated
      (f.col('weeks_since_mod_visit').isin(0,1,2,3)) &
      (f.col('enterprise_seg_prev') == 'lapsed_52_plus_wks'), 'active_reactivated_from_lapsed_52_plus_wks')\
    .when(f.col('weeks_since_mod_visit') < 52, 'active_under_52_wks')\
      .when(f.col('weeks_since_mod_visit')>=52, 'lapsed_52_plus_wks') \
    .otherwise(None))\
  .select('ehhn', 'enterprise_seg', 'weeks_since_mod_visit') \
  .filter(f.col('enterprise_seg').isin('new', 'active_under_52_wks', 'active_reactivated_from_lapsed_52_plus_wks'))

enterprise_seg_curr.display()

# Checking to see if existing 52 Wks HHs are also included
enterprise_seg_curr.groupBy('enterprise_seg').count().display()

ehhn,enterprise_seg_prev
334190572,lapsed_52_plus_wks
64597800422,active_under_52_wks
332899292,lapsed_52_plus_wks
64065500094,active_under_52_wks
313774698,lapsed_52_plus_wks
21266400158,lapsed_52_plus_wks
48187500365,lapsed_52_plus_wks
6176400400,lapsed_52_plus_wks
262035706,active_under_52_wks
231820317,active_under_52_wks


ehhn,enterprise_seg,weeks_since_mod_visit
10000000138,active_under_52_wks,0
100000799,active_under_52_wks,1
100000995,active_under_52_wks,23
100002908,active_under_52_wks,0
10000302,active_under_52_wks,7
100003044,active_under_52_wks,0
100003471,active_under_52_wks,0
100003552,active_under_52_wks,0
100003861,active_under_52_wks,1
100004349,active_under_52_wks,11


enterprise_seg,count
active_reactivated_from_lapsed_52_plus_wks,461580
new,938800
active_under_52_wks,60490825


In [0]:
# # Are there any new HHs that this methodology is missing - check in Vintages for same time period?
# # Still working on figuring out why these HHs wouldn't be in Vintages
# test = enterprise_seg_curr.filter('enterprise_seg == "new"')
# missing = test.join(vintages_ent, how = 'left_anti', on = 'ehhn')
# missing.display()

#### Transactions

In [0]:
# Get transactions for the weeks in question. Added pref_div column for grouping

txrns = acds\
  .get_transactions(
    start_date = start_date,
    end_date = end_date, 
    apply_golden_rules = grs_new, 
    query_filters = ['gtin_no <> "PAPER KROGER"',
                      'gtin_no <> "PAPER MANUF."'],
    join_with=["dates", "stores", "products"],
    join_type="left")\
      .join(pref_div, on = 'ehhn', how = 'left')\
      .join(enterprise_seg_curr, how = 'inner', on = 'ehhn')\
   .withColumn('pref_div',
      f.when((col('pref_div').isNull()) & (col('ehhn').isNull()),'No Loyalty Card')\
      .when((col('pref_div').isNull()) & (col('ehhn').isNotNull()), 'Missing Pref Div')\
      .when((col('pref_div').isNotNull()) & (col('ehhn').isNotNull()), col('pref_div'))\
      .otherwise('error')) \
    .withColumn('enterprise_seg',
      f.when((col('enterprise_seg').isNull()) & (col('ehhn').isNull()),'No Loyalty Card')\
      .when((col('enterprise_seg').isNull()) & (col('ehhn').isNotNull()), 'Missing Enterprise Seg')\
      .when((col('enterprise_seg').isNotNull()) & (col('ehhn').isNotNull()), col('enterprise_seg'))\
      .otherwise('error')) \
  .select(
'ehhn', 'cus_act_no', 'gtin_no', 'sto_no', 'mgt_div_no', 'promo_cycle_week', 'pref_div',
    'enterprise_seg', 'modality', 'transaction_code', 'trn_dt', f.col('pid_fyt_rec_dpt_dsc_tx').alias('dept'), 
    'trn_tm', 'store_code', 'net_spend_amt', 'fiscal_week', 'scn_unt_qy', 'loyalty_disc_amt', 'manufacturer_disc_amt', 
    'match_disc_amt', 'kroger_disc_amt', 'item_snap_flg', 'rtl_dol_am', 'item_wic_flg') \
  .cache()

txrns.limit(50).display()

# for testing, dont write to table. Just print transactions table 

# # write delta table, optimize and cache table

spark.sql(f'DROP TABLE IF EXISTS {db}.transactions_{run_id}')
spark.sql(f'DROP TABLE IF EXISTS transactions_{run_id}_cache')
txrns.write.format('delta').saveAsTable(f'{db}.transactions_{run_id}')
spark.sql(f"OPTIMIZE {db}.transactions_{run_id} ZORDER BY (transaction_code)")
spark.sql(f"CACHE TABLE transactions_{run_id}_cache OPTIONS('storageLevel' 'DISK_ONLY') SELECT * FROM {db}.transactions_{run_id};")
transactions = spark.read.table(f'transactions_{run_id}_cache')

assert transactions.filter(col('pref_div').contains('error')).count() == 0, 'pref_div column contains errors'
assert transactions.filter(col('enterprise_seg').contains('error')).count() == 0, 'enterprise_seg column contains errors'

if print_output:
  transactions.limit(10).toPandas()


/databricks/python/lib/python3.12/site-packages/effodata/dimensions.py:164: DuplicateColumnInJoinWarning: Column bil_div_no is duplicated in join, renaming to stores_bil_div_no
  warnings.warn(


ehhn,cus_act_no,gtin_no,sto_no,mgt_div_no,promo_cycle_week,pref_div,enterprise_seg,modality,transaction_code,trn_dt,dept,trn_tm,store_code,net_spend_amt,fiscal_week,scn_unt_qy,loyalty_disc_amt,manufacturer_disc_amt,match_disc_amt,kroger_disc_amt,item_snap_flg,rtl_dol_am,item_wic_flg
100000550,41641798877,0001111060690,00842,016,20250704,016,active_under_52_wks,INSTORE,016_00842_653_315_20250815_21:19:00,20250815,BAKERY,21:19:00,016_00842,3.99,20250704,1,0.0,0.0,0.0,0.0,N,3.99,N
100000550,41641798877,0001111091620,00842,016,20250703,016,active_under_52_wks,INSTORE,016_00842_554_54_20250811_13:51:00,20250811,FRESH PRODUCE,13:51:00,016_00842,2.78,20250704,2,0.0,0.0,0.0,0.0,N,2.78,N
100000550,41641798877,0001111022301,00842,016,20250702,016,active_under_52_wks,INSTORE,016_00842_554_78_20250801_14:13:00,20250801,FRESH PRODUCE,14:13:00,016_00842,5.0,20250702,1,0.0,0.0,0.0,0.0,N,5.0,N
100000550,41641798877,0002840068198,00842,016,20250604,016,active_under_52_wks,INSTORE,016_00842_555_126_20250721_18:21:00,20250721,GROCERY,18:21:00,016_00842,2.5,20250701,1,2.99,0.0,0.0,0.0,N,5.49,N
100000550,41641798877,0001111010717,00842,016,20250703,016,active_under_52_wks,INSTORE,016_00842_554_54_20250811_13:51:00,20250811,GROCERY,13:51:00,016_00842,4.29,20250704,1,0.0,0.0,0.0,0.0,N,4.29,N
100000550,41641798877,0001111014414,00842,016,20250703,016,active_under_52_wks,INSTORE,016_00842_554_54_20250811_13:51:00,20250811,GROCERY,13:51:00,016_00842,0.6,20250704,1,0.1,0.0,0.0,0.0,N,0.7,N
100000550,41641798877,0009047841001,00842,016,20250703,016,active_under_52_wks,INSTORE,016_00842_654_226_20250812_20:21:00,20250812,GROCERY,20:21:00,016_00842,1.0,20250704,1,0.25,0.0,0.0,0.0,N,1.25,N
100000550,41641798877,0001111065267,00842,016,20250704,016,active_under_52_wks,INSTORE,016_00842_655_121_20250816_12:33:00,20250816,FRESH PRODUCE,12:33:00,016_00842,4.94,20250704,1,3.4,0.0,0.0,0.0,N,8.34,N
100000550,41641798877,0001111065267,00842,016,20250702,016,active_under_52_wks,INSTORE,016_00842_554_78_20250801_14:13:00,20250801,FRESH PRODUCE,14:13:00,016_00842,4.8,20250702,1,2.41,0.0,0.0,0.0,N,7.21,N
100000550,41641798877,0001111065267,00842,016,20250703,016,active_under_52_wks,INSTORE,016_00842_554_54_20250811_13:51:00,20250811,FRESH PRODUCE,13:51:00,016_00842,5.54,20250704,1,0.44,0.0,0.0,0.0,N,5.98,N


#### Delivery

In [0]:
# get delivery modality transactions with spend > 0

delivery_txn = transactions\
  .filter((col('modality')=='DELIVERY'))

# Get all transactions that, when rolled up by transaction code, have spend > 0
delivery_txn_rollup_clean = delivery_txn\
  .groupBy('transaction_code')\
  .agg(f.sum('net_spend_amt').alias('spend'))\
  .filter(col('spend')>0)\
  .select('transaction_code').distinct()

delivery_txn_clean = delivery_txn\
  .join(delivery_txn_rollup_clean.alias('b'),'transaction_code')\
  .select('transaction_code')\
  .withColumn('indicator',f.lit(1))

if print_output:
  print("Counts:")
  print(f"{delivery_txn.count()} rows in delivery_txn")
  print(f"{delivery_txn_rollup_clean.count()} rows in delivery_tnx_rollup_clean")
  print(f"{delivery_txn_clean.count()} rows in delivery_tnx_clean")

  print("Sample 10 rows of delivery_txn_clean: \n")
  delivery_txn_clean.limit(10).display()

#### Pickup

In [0]:
# pickup transactions less any of the outliers below
# households with 1 or more transactions in different divisions on the same date
# households with 4 or more visits on the same day
# households with transactions in more than 1 store or more than one card in the same date and time

pickup_txn = transactions\
  .filter((col('modality')=='PICKUP'))\
  .select('transaction_code','trn_dt','trn_tm','store_code','mgt_div_no','cus_act_no','ehhn')

pu_outlier_1 = pickup_txn\
  .groupBy('ehhn','trn_dt')\
  .agg(f.countDistinct('mgt_div_no').alias('num_div'))\
  .filter(col('num_div')>1)\
  .select('ehhn','trn_dt')
        
pu_outlier_2 = pickup_txn\
  .groupBy('ehhn','trn_dt')\
  .agg(f.countDistinct('transaction_code').alias('num_visits'))\
  .filter(col('num_visits')>4)\
  .select('ehhn','trn_dt')
        
pu_outlier_3 = pickup_txn\
  .groupBy('ehhn','trn_dt','trn_tm')\
  .agg(f.countDistinct('store_code').alias('count_stores'),
  f.countDistinct('cus_act_no').alias('count_cards'))\
  .filter((col('count_stores')>1)|(col('count_cards')>1))\
  .select('ehhn','trn_dt')
        
pu_outliers = pu_outlier_1.union(pu_outlier_2).union(pu_outlier_3)

pickup_txn_clean = pickup_txn.alias('a')\
  .join(pu_outliers.alias('b'),['ehhn','trn_dt'],how='left_anti')\
  .select('a.transaction_code')\
  .withColumn('indicator',f.lit(1))

if print_output:
  print("Counts: \n")
  print(f"{pickup_txn.count()} rows in pickup_txn")
  print(f"{pu_outlier_1.count()} rows in pu_outlier_1")
  print(f"{pu_outlier_2.count()} rows in pu_outlier_2")
  print(f"{pu_outlier_3.count()} rows in pu_outlier_3")

  print("Sample 10 rows of pu_outliers: \n")
  print(pu_outliers.limit(10).display())

  print("Sample 10 rows of pickup_txn_clean: \n")
  pickup_txn_clean.limit(10).display()


#### Combine

In [0]:
# Combine pickup and delivery to transactions 
# add enterprise vintages

final_txn = transactions.alias('a')\
  .join(pickup_txn_clean.alias('f'),'transaction_code',how='left')\
  .join(delivery_txn_clean.alias('g'),'transaction_code',how='left')\
  .select('a.transaction_code')\
  .distinct()

if print_output:
  print(f"{final_txn.count()} rows in final_txn")
  print("Sample 10 rows of final_txn: \n")
  final_txn.limit(10).display()

### Reports

#### Store

In [0]:
basket_store = transactions.alias('a')\
  .join(final_txn.alias('b'),'transaction_code')\
  .groupBy('a.pref_div', 'a.enterprise_seg','a.fiscal_week')\
  .agg(f.countDistinct(f.when(col('scn_unt_qy')>0,col('a.transaction_code'))).alias('visits')
       ,f.countDistinct(f.when(col('scn_unt_qy')>0,col('a.ehhn'))).alias('hhs')
       ,f.sum('rtl_dol_am').alias('gross_sales')
       ,f.sum('net_spend_amt').alias('net_sales')
       ,f.sum('scn_unt_qy').alias('units')
       ,f.sum('loyalty_disc_amt').alias('loy_card_discount')
       ,f.sum('manufacturer_disc_amt').alias('cpg_coup_giveaway')
       ,f.sum('match_disc_amt').alias('krog_match_giveaway')
       ,f.sum('kroger_disc_amt').alias('krog_coup_giveaway')
       ,f.sum(f.when(col('item_snap_flg')=='Y',col('rtl_dol_am'))).alias('snap_gross_sales')
       ,f.sum(f.when(col('item_snap_flg')=='Y',col('net_spend_amt'))).alias('snap_net_sales')
       ,f.countDistinct(
         f.when(((col('scn_unt_qy')>0)&(col('item_snap_flg')=='Y')),
                col('a.transaction_code'))).alias('snap_visits')
       ,f.sum(f.when(col('item_wic_flg')=='Y',col('rtl_dol_am'))).alias('wic_gross_sales')
       ,f.sum(f.when(col('item_wic_flg')=='Y',col('net_spend_amt'))).alias('wic_net_sales')
       ,f.countDistinct(
         f.when(((col('scn_unt_qy')>0)&(col('item_wic_flg')=='Y')),
                col('a.transaction_code'))).alias('wic_visits')
      )


if print_output:
  print(f"{basket_store.count()} rows in basket_store")
  print("Sample 10 rows of basket_store: \n")
  basket_store.limit(10).display()

if write_output:
  # log_counts(basket_store, path=wd+"/bask_store_ecom_counts", fiscal_week = fiscal_week)
  # store in bask_store_files directory
  create_named_csv(
    basket_store,
    path = wd+"/bask_store_omni_files",
    file_name = "bask_store_omni",
    fiscal_week = fiscal_week, 
    mode = mode
  )

  # add to  /send folder to send to nifi
  create_named_csv(
    basket_store,
    path = wd+"/send",
    file_name = "bask_store_omni",
    fiscal_week = fiscal_week, 
    mode = mode
  
  )

In [0]:
#basket_store.display()

#### Department

In [0]:
adweek =  spark.read.table("price_promotions_prd.science.effo_adweek_purered_v")

In [0]:
dept_store = transactions.alias('a')\
  .join(final_txn.alias('b'),'transaction_code')\
  .join(adweek.alias('g'),['promo_cycle_week','store_code','gtin_no'], how = "left")\
  .fillna(0, subset=['adv_typ_cd', 'dpl_typ_cd'])\
  .groupBy('a.pref_div', 'enterprise_seg', 'a.dept', 'a.fiscal_week')\
  .agg(f.countDistinct(f.when(col('a.scn_unt_qy')>0,col('a.transaction_code'))).alias('visits')
       ,f.countDistinct(f.when(col('a.scn_unt_qy')>0,col('a.ehhn'))).alias('hhs')
       ,f.sum('rtl_dol_am').alias('gross_sales')
       ,f.sum('net_spend_amt').alias('net_sales')
       ,f.sum('a.scn_unt_qy').alias('units')
       ,f.sum('loyalty_disc_amt').alias('loy_card_discount')
       ,f.sum('manufacturer_disc_amt').alias('cpg_coup_giveaway')
       ,f.sum('match_disc_amt').alias('krog_match_giveaway')
       ,f.sum('kroger_disc_amt').alias('krog_coup_giveaway')
       ,f.sum(f.when(((col('adv_typ_cd')!='0')&((col('dpl_typ_cd')=='0'))),
                     col('rtl_dol_am'))).alias('adonly_gross_sales')
       ,f.sum(f.when(((col('adv_typ_cd')!='0')&((col('dpl_typ_cd')=='0'))),
                     col('net_spend_amt'))).alias('adonly_net_sales')
       ,f.sum(f.when(((col('adv_typ_cd')!='0')&((col('dpl_typ_cd')=='0'))),
                     col('loyalty_disc_amt'))).alias('adonly_giveaway')
       ,f.sum(f.when(((col('dpl_typ_cd')!='0')&((col('adv_typ_cd')=='0'))),
                     col('rtl_dol_am'))).alias('displayonly_gross_sales')
       ,f.sum(f.when(((col('dpl_typ_cd')!='0')&((col('adv_typ_cd')=='0'))),
                     col('net_spend_amt'))).alias('displayonly_net_sales')
       ,f.sum(f.when(((col('dpl_typ_cd')!='0')&((col('adv_typ_cd')=='0'))),
                     col('loyalty_disc_amt'))).alias('displayonly_giveaway')
       ,f.sum(f.when(((col('dpl_typ_cd')!='0')&(col('adv_typ_cd')!='0')),
                     col('rtl_dol_am'))).alias('adwdisp_gross_sales')
       ,f.sum(f.when(((col('dpl_typ_cd')!='0')&(col('adv_typ_cd')!='0')),
                     col('net_spend_amt'))).alias('adwdisp_net_sales')
       ,f.sum(f.when(((col('dpl_typ_cd')!='0')&(col('adv_typ_cd')!='0')),
                     col('loyalty_disc_amt'))).alias('adwdisp_giveaway')
       ,f.sum(f.when((((col('adv_typ_cd')=='0'))&(col('dpl_typ_cd')=='0')&(col('tpr_fl')=='Y')),
                     col('rtl_dol_am'))).alias('discountonly_gross_sales')
       ,f.sum(f.when((((col('adv_typ_cd')=='0'))&(col('dpl_typ_cd')=='0')&(col('tpr_fl')=='Y')),
                     col('net_spend_amt'))).alias('discountonly_net_sales')
       ,f.sum(f.when((((col('adv_typ_cd')=='0'))&(col('dpl_typ_cd')=='0')&(col('tpr_fl')=='Y')),
                     col('loyalty_disc_amt'))).alias('discountonly_giveaway')
       ,f.sum(f.when((((col('adv_typ_cd')=='0'))&(col('dpl_typ_cd')=='0')&(col('tpr_fl')=='N')),
                     col('rtl_dol_am'))).alias('notrade_gross_sales')
       ,f.sum(f.when((((col('adv_typ_cd')=='0'))&(col('dpl_typ_cd')=='0')&(col('tpr_fl')=='N')),
                     col('net_spend_amt'))).alias('notrade_net_sales')
       ,f.sum(f.when((((col('adv_typ_cd')=='0'))&(col('dpl_typ_cd')=='0')&(col('tpr_fl')=='N')),
                     col('loyalty_disc_amt'))).alias('notrade_giveaway')
      )

if print_output:
  print(f"{dept_store.count()} rows in dept_store")
  print("Sample 10 rows of dept_store: \n")
  dept_store.limit(10).display()

if write_output:
  # log_counts(dept_store, path=wd+"/dept_store_ecom_counts", fiscal_week=fiscal_week, mode = mode)
  # # store in /bask_store_files
  create_named_csv(
    dept_store,
    path = wd+"/dept_store_omni_files",
    file_name = "dept_store_omni",
    fiscal_week = fiscal_week, 
    mode = mode
  )

  # add to /send directory for send to nifi
  create_named_csv(
    dept_store,
    path = wd+"/send",
    file_name = "dept_store_omni",
    fiscal_week = fiscal_week, 
    mode = mode
  )

In [0]:
dept_store.display()

pref_div,enterprise_seg,dept,fiscal_week,visits,hhs,gross_sales,net_sales,units,loy_card_discount,cpg_coup_giveaway,krog_match_giveaway,krog_coup_giveaway,adonly_gross_sales,adonly_net_sales,adonly_giveaway,displayonly_gross_sales,displayonly_net_sales,displayonly_giveaway,adwdisp_gross_sales,adwdisp_net_sales,adwdisp_giveaway,discountonly_gross_sales,discountonly_net_sales,discountonly_giveaway,notrade_gross_sales,notrade_net_sales,notrade_giveaway
035,active_under_52_wks,PKG MEAT,20250701,237859,210409,2529074.619999998,2178002.619999954,511057,306825.01999999944,40020.150000000125,0.0,4226.82999999994,375136.43999999686,272057.4200000003,78072.02000000034,132148.14000000115,108966.73000000097,19906.39000000001,135382.6900000004,101685.87000000032,26918.249999999956,679888.6999999639,546201.1399999697,127975.22000000023,1206518.649999954,1149091.4599999536,53953.140000000065
014,active_under_52_wks,PKG SEAFOOD,20250701,54035,51323,734476.1299999335,596335.6799999475,82917,136422.81000000134,1505.7399999999998,0.0,211.9,41365.880000000085,22557.900000000012,18560.079999999976,128758.64000000036,100721.43000000034,27763.210000000006,23207.630000000012,13014.83999999999,10082.739999999994,181291.53000000137,125415.35000000223,55236.83000000028,359850.6999999814,334624.4099999842,24779.950000000095
025,active_under_52_wks,GROCERY,20250703,1041580,577706,3.253118530000007E7,2.764430292999995E7,8159911,4067017.799999979,733878.709999982,0.0,85985.8599999991,5161855.820000002,3501611.109999991,1284461.3299999882,1269440.7099999553,1035552.7899999634,213141.42000000112,1411863.7899999642,930745.6199999746,395322.62999999715,7100356.27999998,5514108.750000029,1433682.960000003,1.758761922999993E7,1.6662241720000016E7,740406.1800000009
034,active_under_52_wks,PACKAGE PRODUCE,20250703,76040,70485,539170.6599999687,496871.74999997107,118421,40490.87000000028,799.2400000000002,0.0,1008.8,18699.03999999998,11499.880000000005,7197.90999999999,93040.02000000102,83975.6200000006,8696.449999999986,2678.4699999999993,1648.3500000000001,1030.1200000000001,81412.98000000163,66411.26000000023,14747.129999999692,343317.5899999848,333314.0799999862,8819.259999999904
097,active_under_52_wks,GROCERY,20250704,56218,42272,1417551.9299999943,1250012.7799999965,338271,148875.65000000005,18287.54999999992,0.0,375.9499999999998,166563.81000000122,125175.60000000657,33220.26000000061,70638.15000000094,60295.47000000006,9830.309999999923,54141.4200000001,39897.73000000063,11656.52999999993,341024.98999999056,270662.30999999726,66147.49000000025,785183.5599999959,753981.6700000021,28021.06000000026
029,active_under_52_wks,PKG MEAT,20250702,259760,224400,2933823.8699999955,2522932.0099999844,549981,346959.0099999984,49080.30000000015,0.0,14852.550000000041,326258.29999999626,248183.87000000066,62301.12999999994,219292.68000000046,182377.64000000057,31381.480000000076,208718.22999999995,154048.4200000003,41478.610000000015,797706.6799999571,618923.659999961,167620.48000000065,1381847.979999948,1319398.4199999464,44177.30999999982
025,active_under_52_wks,MEAT,20250703,268734,221181,5374471.000000096,5064820.830000086,501994,297297.8899999991,1480.2499999999966,0.0,10872.029999999964,509558.4199999992,375298.6199999988,133536.5499999999,114279.0500000002,109503.95000000019,4662.560000000001,171982.71999999977,136289.22000000026,35292.00000000003,343614.59999999474,303829.0899999976,38819.21000000008,4235036.210000079,4139899.9500000533,84987.56999999954
026,active_reactivated_from_lapsed_52_plus_wks,GROCERY,20250701,3920,3554,131828.7000000034,110740.01000000288,31077,20257.269999999906,795.9700000000006,0.0,35.449999999999996,23821.340000000404,15124.139999999756,8319.639999999945,8052.80999999988,6701.879999999911,1271.4100000000017,9703.529999999924,6005.859999999941,3514.1899999999932,22058.070000000494,17481.039999999986,4471.329999999992,68192.95000000035,65427.09000000006,2680.6999999999985
035,active_reactivated_from_lapsed_52_plus_wks,NATURAL FOODS,20250

In [0]:
if print_output:
  print(dept_store.select("*").count())
  print(dept_store.select("*").distinct().count())

In [0]:
spark.sql(f'DROP TABLE IF EXISTS {db}.transactions_{run_id}')